In [ ]:
! pip install pybaselines
from pybaselines import Baseline

   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 211.9/211.9 kB 3.2 MB/s eta 0:00:00


In [ ]:
from google.colab import drive
import pandas as pd
import plotly.express as px
import numpy as np
from scipy import integrate
from scipy import signal
from scipy.fft import fft, fftfreq
from scipy.interpolate import interp1d
import plotly.express as px
import plotly.graph_objects as go
from plotly.subplots import make_subplots
from pybaselines import Baseline

drive.mount("/content/drive", force_remount=True)

Mounted at /content/drive


In [ ]:
#PATH_DIR = "/content/drive/MyDrive/LLK/Movimento_postivo_x_realinhamento_esquerda_correia/192.168.1.194_20250409_120708.csv"
#PATH_DIR = "/content/drive/MyDrive/LLK/Alinhado/192.168.1.194_20250409_114230.csv"# alinhado
#PATH_DIR = "/content/drive/MyDrive/LLK/Rolete_travado/192.168.1.194_20250409_154158.csv"# roletes travados
#PATH_DIR = "/content/drive/MyDrive/LLK/Sem_dois_roletes/192.168.1.194_20250409_144256.csv"# sem 2 roletes
#PATH_DIR = "/content/drive/MyDrive/LLK/Desalinhamento_direita_em_funcionamento/192.168.1.194_20250409_142555.csv"# deslinhamento direita
#PATH_DIR = "/content/drive/MyDrive/192.168.1.114_20250618_112908.csv"
#PATH_DIR = "/content/drive/MyDrive/LLK/Rolete_travado/192.168.1.194_20250409_154135.csv"
#PATH_DIR = "/content/drive/MyDrive/192.168.1.111_20250704_074347.csv"
#PATH_DIR = "/content/drive/MyDrive/192.168.1.111_20250704_081301.csv"
#PATH_DIR = "/content/drive/MyDrive/192.168.1.111_20250708_082243.csv"

PATH_DIR_1 = "/content/drive/MyDrive/192.168.1.111_20250704_041417.csv"
PATH_DIR_2 = "/content/drive/MyDrive/192.168.1.111_20250704_041430.csv"


df_1 = pd.read_csv(PATH_DIR_1)
df_2 = pd.read_csv(PATH_DIR_2)

df = pd.concat([df_1, df_2], ignore_index=True)

#df = pd.read_csv(PATH_DIR)

########################################
## A sequencia que o sensor envia os dados é (x_accel, x_gyro, y_accel, y_gyro, z_accel, z_gyro) o servidor acabou aderindo cabeçalho (x_accel, y_accel, z_accel, x_gyro, y_gyro, z_gyro), logo a sequencia abaixo foi alterada para sequencializar as informações como de fato foram enviadas.
# Lista de ips que indicam arquivos que foram coletados com indice trocado
sensor_dest = ["192.168.1.111", "", ""]

if any(sensor in PATH_DIR_1 for sensor in sensor_dest):
    df = df.rename(columns={
        'x_data': 'x_data',
        'y_data': 'x_gyro',
        'z_data': 'y_data',
        'x_gyro': 'y_gyro',
        'y_gyro': 'z_data',
        'z_gyro': 'z_gyro'
        # temp continua igual
    })
########################################

print(df.head())

   x_data  x_gyro  y_data  y_gyro  z_data  z_gyro  temp
0      77      51     286     -94    -615       7  -886
1      92      25     278    -213    -548      12  -888
2     129     -23     287     189    -601      -8  -888
3      80      -2     264     144    -707      -4  -886
4     122      65     260     115    -617      -5  -888


In [ ]:
# Parâmetros de conversão
RANGE_ACC = 16  # RANGE em G
RANGE_GYRO = 2000  # RANGE em dps
CONVERSION_FACTOR_ACC = ((2 * RANGE_ACC) / (2**15)) * 9.81  # Fator de conversão para m/s²
CONVERSION_FACTOR_GYRO = ((2 * RANGE_GYRO) / (2**15))  # Fator de conversão para °/s
DT = 0.02
BELT_SPEED = 4.7 # m/s
BELT_LENGTH = 1000  # m

# Parâmetros filtro passa-baixa
LOWPASS_CUTOFF_ACC = 10
LOWPASS_CUTOFF_GYRO = 20
FILTER_ORDER_ACC = 4
FILTER_ORDER_GYRO = 4

# X axis base: distância = 1, tempo = 2, amostra = 3,
AXIS_SELECTION = 3

def get_x_base_label(axis):
    match axis:
        case 1:
            return "distância[m]"
        case 2:
            return "tempo[s]"
        case 3:
            return "amostra"

x_base_label = get_x_base_label(AXIS_SELECTION)

def filter_signal(data, cutoff, order, dt):
    fs = 1 / dt
    lowpass_filter = signal.butter(order, cutoff, btype='lowpass', fs=fs, output='sos')
    filtered_signal = signal.sosfilt(lowpass_filter, data)
    return filtered_signal

def correct_gravity_dynamically(data):
    # Conversão dos dados do acelerômetro
    acc_x = np.array(data['x_data'], dtype=float) * CONVERSION_FACTOR_ACC
    acc_y = np.array(data['y_data'], dtype=float) * CONVERSION_FACTOR_ACC
    acc_z = np.array(data['z_data'], dtype=float) * CONVERSION_FACTOR_ACC

    # Calcular a magnitude total da gravidade
    acc_magnitude = np.sqrt(acc_x**2 + acc_y**2 + acc_z**2)

    # Filtro passa-baixa para estimar a gravidade
    gravity_magnitude = filter_signal(acc_magnitude, cutoff=1, order=4, dt=DT)

    # Estimar os componentes da gravidade em cada eixo
    gravity_x = (acc_x / acc_magnitude) * gravity_magnitude
    gravity_y = (acc_y / acc_magnitude) * gravity_magnitude
    gravity_z = (acc_z / acc_magnitude) * gravity_magnitude

    # Remover os componentes da gravidade
    acc_x_corrected = acc_x - gravity_x
    acc_y_corrected = acc_y - gravity_y
    acc_z_corrected = acc_z - gravity_z

    return acc_x_corrected, acc_y_corrected, acc_z_corrected

def process_sensor_data(acc_signal, gyro_signal):

    sample = np.arange(len(acc_signal))
    acc_signal_ms2 = np.array(acc_signal, dtype=float) * CONVERSION_FACTOR_ACC
    gyro_signal_dps = np.array(gyro_signal, dtype=float) * CONVERSION_FACTOR_GYRO

    # Filtro passa-baixa
    acc_signal_filtered = filter_signal(acc_signal_ms2, LOWPASS_CUTOFF_ACC, FILTER_ORDER_ACC, DT)
    gyro_signal_filtered = filter_signal(gyro_signal_dps, LOWPASS_CUTOFF_GYRO, FILTER_ORDER_GYRO, DT)

    # Detrend
    acc_signal_detrended = signal.detrend(acc_signal_filtered, type='constant')
    gyro_signal_detrended = signal.detrend(gyro_signal_filtered, type='constant')
    #acc_signal_detrended = acc_signal_ms2
    #gyro_signal_detrended = gyro_signal_dps

    # Calculo de velocidade
    speed = integrate.cumulative_trapezoid(acc_signal_detrended, dx=DT, initial=0)
    baseline_fitter_speed = Baseline(x_data=sample)
    half_window = 1000
    speed_drift, _ = baseline_fitter_speed.std_distribution(speed, half_window, smooth_half_window=10)
    speed_corrected = speed - speed_drift
    position = integrate.cumulative_trapezoid(speed_corrected, dx=DT, initial=0)

    # Calculo de ângulo
    degree = integrate.cumulative_trapezoid(gyro_signal_detrended, dx=DT, initial=0)
    baseline_fitter_degree = Baseline(x_data=sample)
    degree_drift, _ = baseline_fitter_degree.std_distribution(degree, half_window, smooth_half_window=10)
    degree_corrected = degree - degree_drift

    # Calculo FFT
    '''
    sample2 = len(acc_signal)
    af = fft(acc_signal_detrended)
    gf = fft(gyro_signal_detrended)
    xf = fftfreq(sample2, DT)
    xf_positive = xf[:sample2//2]
    af_magnitude_normalized = 2.0/sample2 * np.abs(af[0:sample2//2])
    gf_magnitude_normalized = 2.0/sample2 * np.abs(gf[0:sample2//2])

    '''

    # Defina o intervalo em segundos
    T0 = 0.0   # início em segundos
    T1 = 250.0   # fim em segundos

    # Converte em índices
    i0 = int(np.floor(T0 / DT))
    i1 = int(np.floor(T1 / DT))

    # Fatia os sinais
    acc_seg = acc_signal_detrended[i0:i1]
    gyro_seg = gyro_signal_detrended[i0:i1]
    N_seg = len(acc_seg)

    # FFT do segmento
    Af = fft(acc_seg)
    Gf = fft(gyro_seg)
    xf_positive = fftfreq(N_seg, DT)[:N_seg//2]

    af_magnitude_normalized = 2.0/N_seg * np.abs(Af[:N_seg//2])
    gf_magnitude_normalized = 2.0/N_seg * np.abs(Gf[:N_seg//2])

    if x_base_label == "distância[m]":
        sample_x_axis = DT * BELT_SPEED * sample
    elif x_base_label == "tempo[s]":
        sample_x_axis = DT * sample
    else:
        sample_x_axis = sample


    # Monta dataframes
    acc_data_df = pd.DataFrame({x_base_label: sample_x_axis, "m/s²": acc_signal_detrended})
    speed_data_df = pd.DataFrame({x_base_label: sample_x_axis, "m/s": speed_corrected})
    position_data_df = pd.DataFrame({x_base_label: sample_x_axis, "m": position})
    gyro_data_df = pd.DataFrame({x_base_label: sample_x_axis, "°/s": gyro_signal_detrended})
    degree_data_df = pd.DataFrame({x_base_label: sample_x_axis, "°": degree_corrected})
    fft_df = pd.DataFrame({'Frequencia (Hz)': xf_positive,'Amplitude': af_magnitude_normalized})
    fft_gf = pd.DataFrame({'Frequencia (Hz)': xf_positive,'Amplitude': gf_magnitude_normalized})

    return acc_data_df, speed_data_df, position_data_df, gyro_data_df, degree_data_df, fft_df, fft_gf

def process_temperature_data(temp_values):
    sample = np.arange(len(temp_values))
    temp_data_celsius = (np.array(temp_values, dtype=float) / 132.48) + 25
    temp_data_celsius_avg = np.mean(temp_data_celsius)
    temp_df = pd.DataFrame({"amostra": sample, "°C": temp_data_celsius_avg})
    return temp_df

def combine_acc_vel_data(acc_df, vel_df, pos_df):
    combined_data = pd.concat([acc_df, vel_df, pos_df], keys=['Aceleração', 'Velocidade', 'Posição'])
    melted_data = pd.melt(combined_data.reset_index(), id_vars=[x_base_label], value_vars=['m/s²', 'm/s', 'm'], var_name='Série', value_name='Valor')
    return melted_data

def combine_gyro_degree_data(gyro_df, degree_df):
    combined_data = pd.concat([gyro_df, degree_df], keys=['Velocidade Angular', 'Ângulo'])
    melted_data = pd.melt(combined_data.reset_index(), id_vars=[x_base_label], value_vars=['°/s', '°'], var_name='Série', value_name='Valor')
    return melted_data

#Correção dinâmica de força G
acc_x_corrected, acc_y_corrected, acc_z_corrected = correct_gravity_dynamically(df)

df_acc_x, df_speed_x, df_position_x, df_gyro_x, df_degree_x, df_fft_acc_x, df_fft_gyro_x = process_sensor_data(acc_x_corrected, df['x_gyro'])
df_acc_y, df_speed_y, df_position_y, df_gyro_y, df_degree_y, df_fft_acc_y, df_fft_gyro_y = process_sensor_data(acc_y_corrected, df['y_gyro'])
df_acc_z, df_speed_z, df_position_z, df_gyro_z, df_degree_z, df_fft_acc_z, df_fft_gyro_z = process_sensor_data(acc_z_corrected, df['z_gyro'])
df_temp = process_temperature_data(df['temp'])


melted_data_acc_x = combine_acc_vel_data(df_acc_x, df_speed_x, df_position_x)
melted_data_acc_y = combine_acc_vel_data(df_acc_y, df_speed_y, df_position_y)
melted_data_acc_z = combine_acc_vel_data(df_acc_z, df_speed_z, df_position_z)

melted_data_gyro_x = combine_gyro_degree_data(df_gyro_x, df_degree_x)
melted_data_gyro_y = combine_gyro_degree_data(df_gyro_y, df_degree_y)
melted_data_gyro_z = combine_gyro_degree_data(df_gyro_z, df_degree_z)

#Gráficos de aceleração e velocidade

In [ ]:
fig_combined_x = px.line(melted_data_acc_x, x = x_base_label, y="Valor", color="Série", title='Aceleração e Velocidade em [X]',template="plotly_dark", width=1200, height=500)


# Definindo os ticks do eixo X a cada 50 metros
min_x = melted_data_acc_x[x_base_label].min()
max_x = melted_data_acc_x[x_base_label].max()
tick_vals = list(range(int(min_x), int(max_x) + 1, 50))

fig_combined_x.update_layout(
    xaxis=dict(
        tickmode='array',
        tickvals=tick_vals,
        tickangle=0
    )
)

fig_combined_x.show()

In [ ]:
fig_combined_y = px.line(melted_data_acc_y, x = x_base_label, y="Valor", color="Série", title='Aceleração e Velocidade em [Y]', template="plotly_dark", width=1200, height=500)

# Definindo os ticks do eixo X a cada 50 metros
min_x = melted_data_acc_x[x_base_label].min()
max_x = melted_data_acc_x[x_base_label].max()
tick_vals = list(range(int(min_x), int(max_x) + 1, 50))

fig_combined_y.update_layout(
    xaxis=dict(
        tickmode='array',
        tickvals=tick_vals,
        tickangle=0
    )
)

fig_combined_y.show()

In [ ]:
fig_combined_z = px.line(melted_data_acc_z, x = x_base_label, y="Valor", color="Série", title='Aceleração e Velocidade em [Z]', template="plotly_dark", width=1200, height=500)

# Definindo os ticks do eixo X a cada 50 metros
min_x = melted_data_acc_x[x_base_label].min()
max_x = melted_data_acc_x[x_base_label].max()
tick_vals = list(range(int(min_x), int(max_x) + 1, 50))

fig_combined_z.update_layout(
    xaxis=dict(
        tickmode='array',
        tickvals=tick_vals,
        tickangle=0
    )
)

fig_combined_z.show()

#Gráficos de velocidade angular e ângulo

In [ ]:
fig_combined_x = px.line(melted_data_gyro_x, x = x_base_label, y="Valor", color="Série", title='Velocidade e Ângulo em [X]',template="plotly_dark", width=1200, height=500)

# Definindo os ticks do eixo X a cada 50 metros
min_x = melted_data_acc_x[x_base_label].min()
max_x = melted_data_acc_x[x_base_label].max()
tick_vals = list(range(int(min_x), int(max_x) + 1, 50))

fig_combined_x.update_layout(
    xaxis=dict(
        tickmode='array',
        tickvals=tick_vals,
        tickangle=0
    )
)

fig_combined_x.show()

In [ ]:
fig_combined_y = px.line(melted_data_gyro_y, x = x_base_label, y="Valor", color="Série", title='Velocidade e Ângulo em [Y]',template="plotly_dark", width=1200, height=500)

# Definindo os ticks do eixo X a cada 50 metros
min_x = melted_data_acc_x[x_base_label].min()
max_x = melted_data_acc_x[x_base_label].max()
tick_vals = list(range(int(min_x), int(max_x) + 1, 50))

fig_combined_y.update_layout(
    xaxis=dict(
        tickmode='array',
        tickvals=tick_vals,
        tickangle=0
    )
)

fig_combined_y.show()

In [ ]:
  fig_combined_z = px.line(melted_data_gyro_z, x = x_base_label, y="Valor", color="Série", title='Velocidade e Ângulo em [Z]',template="plotly_dark", width=1200, height=500)

# Definindo os ticks do eixo X a cada 50 metros
min_x = melted_data_acc_x[x_base_label].min()
max_x = melted_data_acc_x[x_base_label].max()
tick_vals = list(range(int(min_x), int(max_x) + 1, 50))

fig_combined_z.update_layout(
    xaxis=dict(
        tickmode='array',
        tickvals=tick_vals,
        tickangle=0
    )
)


fig_combined_z.show()

# Gráficos de FFT da aceleração


In [ ]:
fig_fft_x = px.line(df_fft_acc_x, x="Frequencia (Hz)", y="Amplitude", title='FFT - [X]',template="plotly_dark", width=1200, height=500)
fig_fft_x.show()

In [ ]:
fig_fft_y = px.line(df_fft_acc_y, x="Frequencia (Hz)", y="Amplitude", title='FFT - [Y]',template="plotly_dark", width=1200, height=500)
fig_fft_y.show()

In [ ]:
fig_fft_z = px.line(df_fft_acc_z, x="Frequencia (Hz)", y="Amplitude", title='FFT - [Z]',template="plotly_dark", width=1200, height=500)
fig_fft_z.show()

# Gráficos de FFT da velocidade angular

In [ ]:
fig_fft_x = px.line(df_fft_gyro_x, x="Frequencia (Hz)", y="Amplitude", title='FFT - [X]',template="plotly_dark", width=1200, height=500)
fig_fft_x.show()

In [ ]:
fig_fft_y = px.line(df_fft_gyro_y, x="Frequencia (Hz)", y="Amplitude", title='FFT - [Y]',template="plotly_dark", width=1200, height=500)
fig_fft_y.show()

In [ ]:
fig_fft_z = px.line(df_fft_gyro_z, x="Frequencia (Hz)", y="Amplitude", title='FFT - [Z]',template="plotly_dark", width=1200, height=500)
fig_fft_z.show()

# Gráfico de temperatura

In [ ]:
fig_temp = px.line(df_temp, x="amostra", y="°C", title='Temperatura em [°C]', template="plotly_dark", width=1200, height=500)
fig_temp.show()

# RAW DATA PLOT

In [ ]:
def plot_converted_raw_sensor_data(df):
    # Aplica fatores de conversão
    acc_x = np.array(df['x_data'], dtype=float) * CONVERSION_FACTOR_ACC
    acc_y = np.array(df['y_data'], dtype=float) * CONVERSION_FACTOR_ACC
    acc_z = np.array(df['z_data'], dtype=float) * CONVERSION_FACTOR_ACC

    gyro_x = np.array(df['x_gyro'], dtype=float) * CONVERSION_FACTOR_GYRO
    gyro_y = np.array(df['y_gyro'], dtype=float) * CONVERSION_FACTOR_GYRO
    gyro_z = np.array(df['z_gyro'], dtype=float) * CONVERSION_FACTOR_GYRO

    sample = list(range(len(df)))

    fig = make_subplots(
        rows=3, cols=2,
        subplot_titles=[
            "Accel X [m/s²]", "Gyro X [°/s]",
            "Accel Y [m/s²]", "Gyro Y [°/s]",
            "Accel Z [m/s²]", "Gyro Z [°/s]"
        ],
        shared_xaxes=True,
        vertical_spacing=0.05,
        horizontal_spacing=0.1
    )

    # Aceleração convertida
    fig.add_trace(go.Scatter(x=sample, y=acc_x, name="Accel X"), row=1, col=1)
    fig.add_trace(go.Scatter(x=sample, y=acc_y, name="Accel Y"), row=2, col=1)
    fig.add_trace(go.Scatter(x=sample, y=acc_z, name="Accel Z"), row=3, col=1)

    # Giroscópio convertido
    fig.add_trace(go.Scatter(x=sample, y=gyro_x, name="Gyro X"), row=1, col=2)
    fig.add_trace(go.Scatter(x=sample, y=gyro_y, name="Gyro Y"), row=2, col=2)
    fig.add_trace(go.Scatter(x=sample, y=gyro_z, name="Gyro Z"), row=3, col=2)

    # Layout escuro com tamanho definido
    fig.update_layout(
        template='plotly_dark',
        height=700,
        width=1200,
        title_text="Dados convertidos - Aceleração (m/s²) e Velocidade Angular (°/s)",
        showlegend=False
    )

    fig.update_xaxes(title_text="Amostra", row=3, col=1)
    fig.update_xaxes(title_text="Amostra", row=3, col=2)
    fig.update_yaxes(title_text="m/s²", row=1, col=1)
    fig.update_yaxes(title_text="°/s", row=1, col=2)

    fig.show()

plot_converted_raw_sensor_data(df)

In [ ]:
def plot_filtered_converted_sensor_data(df):
    # Conversão
    acc_x = np.array(df['x_data'], dtype=float) * CONVERSION_FACTOR_ACC
    acc_y = np.array(df['y_data'], dtype=float) * CONVERSION_FACTOR_ACC
    acc_z = np.array(df['z_data'], dtype=float) * CONVERSION_FACTOR_ACC

    gyro_x = np.array(df['x_gyro'], dtype=float) * CONVERSION_FACTOR_GYRO
    gyro_y = np.array(df['y_gyro'], dtype=float) * CONVERSION_FACTOR_GYRO
    gyro_z = np.array(df['z_gyro'], dtype=float) * CONVERSION_FACTOR_GYRO

    # Filtro passa-baixa
    acc_x_filtered = filter_signal(acc_x, cutoff=1, order=4, dt=DT)
    acc_y_filtered = filter_signal(acc_y, cutoff=1, order=4, dt=DT)
    acc_z_filtered = filter_signal(acc_z, cutoff=1, order=4, dt=DT)

    gyro_x_filtered = filter_signal(gyro_x, cutoff=5)
    gyro_y_filtered = filter_signal(gyro_y, cutoff=5)
    gyro_z_filtered = filter_signal(gyro_z, cutoff=5)

    sample = list(range(len(df)))

    fig = make_subplots(
        rows=3, cols=2,
        subplot_titles=[
            "Accel X [m/s²]", "Gyro X [°/s]",
            "Accel Y [m/s²]", "Gyro Y [°/s]",
            "Accel Z [m/s²]", "Gyro Z [°/s]"
        ],
        shared_xaxes=True,
        vertical_spacing=0.05,
        horizontal_spacing=0.1
    )

    # Aceleração filtrada
    fig.add_trace(go.Scatter(x=sample, y=acc_x_filtered, name="Accel X"), row=1, col=1)
    fig.add_trace(go.Scatter(x=sample, y=acc_y_filtered, name="Accel Y"), row=2, col=1)
    fig.add_trace(go.Scatter(x=sample, y=acc_z_filtered, name="Accel Z"), row=3, col=1)

    # Giroscópio filtrado
    fig.add_trace(go.Scatter(x=sample, y=gyro_x_filtered, name="Gyro X"), row=1, col=2)
    fig.add_trace(go.Scatter(x=sample, y=gyro_y_filtered, name="Gyro Y"), row=2, col=2)
    fig.add_trace(go.Scatter(x=sample, y=gyro_z_filtered, name="Gyro Z"), row=3, col=2)

    fig.update_layout(
        template='plotly_dark',
        height=700,
        width=1200,
        title_text="Dados filtrados - Aceleração (m/s²) e Velocidade Angular (°/s)",
        showlegend=False
    )

    fig.update_xaxes(title_text="Amostra", row=3, col=1)
    fig.update_xaxes(title_text="Amostra", row=3, col=2)
    fig.update_yaxes(title_text="m/s²", row=1, col=1)
    fig.update_yaxes(title_text="°/s", row=1, col=2)

    fig.show()

plot_filtered_converted_sensor_data(df)

# Animação Vetorial

In [ ]:
def animate_acceleration_vector(df, step=1):
    # Dados convertidos
    acc_x = np.array(df['x_data'], dtype=float) * CONVERSION_FACTOR_ACC
    acc_y = np.array(df['y_data'], dtype=float) * CONVERSION_FACTOR_ACC
    acc_z = np.array(df['z_data'], dtype=float) * CONVERSION_FACTOR_ACC

    acc_x_filtered = filter_signal(acc_x)
    acc_y_filtered = filter_signal(acc_y)
    acc_z_filtered = filter_signal(acc_z)

    # Subamostragem para performance (1 frame a cada `step` amostras)
    indices = range(0, len(acc_x), step)

    # Frames para a animação
    frames = []
    for i in indices:
        frames.append(go.Frame(
            data=[
                go.Cone(
                    x=[0], y=[0], z=[0],
                    u=[acc_x_filtered[i]], v=[acc_z_filtered[i]], w=[acc_y_filtered[i]],
                    anchor="tail",
                    sizemode="absolute", sizeref=1.5,
                    colorscale='Blues',
                    showscale=False
                )
            ],
            name=str(i)
        ))

    # Primeiro vetor (inicial)
    initial_cone = go.Cone(
        x=[0], y=[0], z=[0],
        u=[acc_x_filtered[0]], v=[acc_z_filtered[0]], w=[acc_y_filtered[0]],
        #u=[0], v=[0], w=[1],
        anchor="tail",
        sizemode="absolute", sizeref=1.5,
        colorscale='Blues',
        showscale=False
    )

    fig = go.Figure(
        data=[initial_cone],
        frames=frames,
        layout=go.Layout(
            title="Animação do vetor de aceleração no tempo",
            scene=dict(
                xaxis=dict(range=[-20, 20], title="X"),
                yaxis=dict(range=[-20, 20], title="Y"),
                zaxis=dict(range=[-20, 20], title="Z"),
                aspectmode='cube'
            ),
            template='plotly_dark',
            width=700,
            height=700,
            updatemenus=[dict(
                type="buttons",
                showactive=False,
                y=1,
                x=1.2,
                xanchor="right",
                yanchor="top",
                buttons=[
                    dict(label="▶️ Play", method="animate", args=[None, {"frame": {"duration": 30, "redraw": True}, "fromcurrent": True}]),
                    dict(label="⏸ Pause", method="animate", args=[[None], {"frame": {"duration": 0, "redraw": False}, "mode": "immediate"}])
                ]
            )]
        )
    )

    fig.show()

animate_acceleration_vector(df, step=30)

# Animação em Plano

In [ ]:
def animate_inclination_plane(df, step=5, duration_total_ms=300_000):
    acc_x = np.array(df['x_data'], dtype=float) * CONVERSION_FACTOR_ACC
    acc_y = np.array(df['y_data'], dtype=float) * CONVERSION_FACTOR_ACC
    acc_z = np.array(df['z_data'], dtype=float) * CONVERSION_FACTOR_ACC

    acc_x_filtered = filter_signal(acc_x)
    acc_y_filtered = filter_signal(acc_y)
    acc_z_filtered = filter_signal(acc_z)


    indices = range(0, len(acc_x), step)
    total_frames = len(indices)
    duration_per_frame = duration_total_ms / total_frames  # em ms

    def create_plane(ax, ay, az, size=10):
        # Cria uma grade no plano XY
        grid_range = np.linspace(-size, size, 10)
        xx, yy = np.meshgrid(grid_range, grid_range)
        zz = np.zeros_like(xx)

        # vetor normal (aceleração)
        normal = np.array([ax, ay, az])
        normal = normal / np.linalg.norm(normal)

        # vetor normal padrão (plano horizontal)
        base_normal = np.array([0, 0, 1])

        # eixo de rotação (produto vetorial)
        axis = np.cross(base_normal, normal)
        angle = np.arccos(np.clip(np.dot(base_normal, normal), -1.0, 1.0))

        if np.linalg.norm(axis) == 0:
            return xx, yy, zz  # já está alinhado

        # matriz de rotação usando fórmula de Rodrigues
        axis = axis / np.linalg.norm(axis)
        K = np.array([[0, -axis[2], axis[1]],
                      [axis[2], 0, -axis[0]],
                      [-axis[1], axis[0], 0]])
        R = np.eye(3) + np.sin(angle) * K + (1 - np.cos(angle)) * (K @ K)

        # aplica a rotação
        points = np.stack([xx.flatten(), yy.flatten(), zz.flatten()], axis=0)
        rotated = R @ points
        x_rot, y_rot, z_rot = rotated.reshape(3, *xx.shape)

        return x_rot, y_rot, z_rot

    # cria os frames
    frames = []
    for i in indices:
        X, Y, Z = create_plane(acc_x_filtered[i], acc_y_filtered[i], acc_z_filtered[i])

        # matriz de cor fixa: metade azul, metade vermelha
        color_matrix = np.zeros_like(X)
        color_matrix[:, :color_matrix.shape[1]//2] = 0  # Azul
        color_matrix[:, color_matrix.shape[1]//2:] = 1  # Vermelho

        surface = go.Surface(
            x=X, y=Y, z=Z,
            surfacecolor=color_matrix,
            cmin=0,
            cmax=1,
            colorscale=[[0, 'blue'], [1, 'red']],
            showscale=False,
            opacity=1
        )


        frames.append(go.Frame(data=[surface], name=str(i)))

    # primeiro plano
    X0, Y0, Z0 = create_plane(acc_x_filtered[0], acc_y_filtered[0], acc_z_filtered[0])
    surface0 = go.Surface(x=X0, y=Y0, z=Z0, colorscale='Blues', showscale=False, opacity=1)

    fig = go.Figure(
        data=[surface0],
        frames=frames,
        layout=go.Layout(
            title="Animação de plano inclinado pelo vetor de aceleração",
            scene=dict(
                xaxis=dict(range=[-20, 20], title="X"),
                yaxis=dict(range=[-20, 20], title="Y"),
                zaxis=dict(range=[-20, 20], title="Z"),
                aspectmode='cube'
            ),
            template='plotly_dark',
            width=800,
            height=700,
            updatemenus=[dict(
                type="buttons",
                showactive=False,
                y=1,
                x=1.15,
                xanchor="right",
                yanchor="top",
                buttons=[
                    dict(label="▶️ Play", method="animate",
                         args=[None, {
                             "frame": {"duration": duration_per_frame, "redraw": True},
                             "fromcurrent": True}]),
                    dict(label="⏸ Pause", method="animate",
                         args=[[None], {
                             "frame": {"duration": 0, "redraw": False},
                             "mode": "immediate"}])
                ]
            )]
        )
    )

    fig.show()

animate_inclination_plane(df, step=30, duration_total_ms=100_00)

In [ ]:
def animate_acceleration_trajectory(df, step=1):
    # Dados convertidos
    acc_x = np.array(df['x_data'], dtype=float) * CONVERSION_FACTOR_ACC
    acc_y = np.array(df['y_data'], dtype=float) * CONVERSION_FACTOR_ACC
    acc_z = np.array(df['z_data'], dtype=float) * CONVERSION_FACTOR_ACC

    acc_x_filtered = filter_signal(acc_z)
    acc_z_filtered = filter_signal(acc_y)
    acc_y_filtered = filter_signal(acc_x)

    indices = range(0, len(acc_x), step)
    line_length_scale = 0.2  # fator que representa o "tempo" de cada deslocamento

    # Ponto inicial
    x_traj = [0]
    y_traj = [0]
    z_traj = [0]

    frames = []

    for i in indices:
                # vetor atual
        vx = acc_x_filtered[i]
        vy = acc_y_filtered[i]
        vz = acc_z_filtered[i]

        norm = np.linalg.norm([vx, vy, vz])
        if norm == 0:
            norm = 1  # evita divisão por zero

        # deslocamento constante (norm = 1)
        dx = (vx / norm) * line_length_scale
        dy = (vy / norm) * line_length_scale
        dz = (vz / norm) * line_length_scale

        # novo ponto da trajetória
        x_traj.append(x_traj[-1] + dx)
        y_traj.append(y_traj[-1] + dy)
        z_traj.append(z_traj[-1] + dz)

        frames.append(go.Frame(
            data=[
                go.Cone(
                    x=[x_traj[-1]], y=[y_traj[-1]], z=[z_traj[-1]],
                    u=[vx], v=[vy], w=[vz],
                    anchor="tail",
                    sizemode="absolute", sizeref=1.5,
                    colorscale='Blues',
                    showscale=False
                ),
                go.Scatter3d(
                    x=x_traj,
                    y=y_traj,
                    z=z_traj,
                    mode='lines',
                    line=dict(color='orange', width=4),
                    showlegend=False
                )
            ],
            name=str(i)
        ))


    # Inicial
    ux0, uy0, uz0 = acc_x_filtered[0], acc_y_filtered[0], acc_z_filtered[0]
    initial_cone = go.Cone(
        x=[0], y=[0], z=[0],
        u=[ux0], v=[uy0], w=[uz0],
        anchor="tail",
        sizemode="absolute", sizeref=1.5,
        colorscale='Blues',
        showscale=False
    )
    initial_line = go.Scatter3d(
        x=[0],
        y=[0],
        z=[0],
        mode='lines',
        line=dict(color='orange', width=4),
        showlegend=False
    )

    layout=go.Layout(
    title="Trajetória acumulada da aceleração (como deslocamento)",
    scene=dict(
        xaxis=dict(range=[-500, 500], title="X"),
        yaxis=dict(range=[-500, 500], title="Y"),
        zaxis=dict(range=[-500, 500], title="Z"),
        aspectmode='cube'
    ),
    template='plotly_dark',
    width=700,
    height=700,
    updatemenus=[dict(
        type="buttons",
        showactive=False,
        y=1,
        x=1.2,
        xanchor="right",
        yanchor="top",
        buttons=[
            dict(label="▶️ Play", method="animate", args=[None, {"frame": {"duration": 1, "redraw": True}, "fromcurrent": True}]),
            dict(label="⏸ Pause", method="animate", args=[[None], {"frame": {"duration": 0, "redraw": False}, "mode": "immediate"}]),
            dict(label="🔄 Reset", method="animate", args=[None, {"frame": {"duration": 0, "redraw": True}, "mode": "immediate", "fromcurrent": False}])
        ]
    )]
)

    fig = go.Figure(
        data=[initial_cone, initial_line],
        frames=frames,
        layout=layout
    )
    fig.show()

animate_acceleration_trajectory(df, step=30)

